In [1]:
from utils.data_utils import load_enhanced_df, load_reddit_df
import pandas as pd
import networkx as nx
from typing import Union
import os
import seaborn as sns
import matplotlib.pyplot as plt
import numpy as np 




In [ ]:
df_final = load_reddit_df(r"ada-2025-project-standard-deviants-ada\data\reddit_df_final_superclusters.pkl") 
# from utils.data_utils import load_final_df, load_reddit_df
# df_final = load_final_df()  

df_final = df_final[["source_supercluster","SOURCE_SUBREDDIT","TARGET_SUBREDDIT", "score","TIMESTAMP", "subreddit_subscribers","ups"]]
# df_final.head()
len(df_final)

858488

In [ ]:
WINDOW = 5000

dfs_by_supercluster = {}
df_final["virality_rss"] = df_final["score"] / (df_final["subreddit_subscribers"]+6)
for supercluster, df_sc in df_final.groupby("source_supercluster"):
    df_sc = df_sc.copy()
    df_sc = df_sc.sort_values("TIMESTAMP")
    df_sc["ups_ma"] = df_sc["ups"].rolling(WINDOW, min_periods=1000).mean()
    df_sc["ups_std"] = df_sc["ups"].rolling(WINDOW, min_periods=1000).std()
    df_sc["is_viral"] = df_sc["ups"] > (df_sc["ups_ma"] + 30* df_sc["ups_std"]) 
    df_sc["virality_rss_std"] = df_sc["virality_rss"].rolling(WINDOW, min_periods=1000).std() 
    df_sc["virality_rss_ma"] = df_sc["virality_rss"].ewm(span=10000, adjust=False).mean()
    df_sc["is_viral_rss"]=df_sc["virality_rss"] > (df_sc["virality_rss_ma"] + 30* df_sc["virality_rss_std"]) 
    df_sc["subreddit_occ_index"] = (
    df_sc.groupby("SOURCE_SUBREDDIT").cumcount() + 1 )
    dfs_by_supercluster[supercluster] = df_sc

for supercluster, df_sc in dfs_by_supercluster.items():
    n_true = df_sc["is_viral_rss"].sum()   
    print(supercluster, n_true)


Gaming & Interactive Entertainment 5
Lifestyle & Niche Interests 0
Politics & Society 6
Pop Culture & Media 13
Reddit Meta & Community 19
Sports & Athletics 2
Technology & Digital Culture 1


In [ ]:
import plotly.graph_objects as go
from plotly.subplots import make_subplots

clusters = sorted(dfs_by_supercluster.keys())

fig = make_subplots(
    rows=len(clusters),
    cols=1,
    shared_xaxes=True,
    subplot_titles=[f"Supercluster {c}" for c in clusters]
)

for i, cluster in enumerate(clusters, start=1):
    df_sc = dfs_by_supercluster[cluster]
    df_sc = df_sc.sort_values("TIMESTAMP")

    
    fig.add_trace(
        go.Scatter(
            x=df_sc["TIMESTAMP"],
            y=df_sc["ups_ma"],
            mode="lines",
            name="Moving Average",
            showlegend=(i == 1)
        ),
        row=i, col=1
    )

   
    viral = df_sc[df_sc["is_viral"]]
    fig.add_trace(
        go.Scatter(
        x=viral["TIMESTAMP"],
        y=viral["ups"],
        mode="markers",
        name=f"Viral – cluster {cluster}",
        marker=dict(size=5, symbol="circle-open"),
        showlegend=(i == 1),
        text=[
            f"<b>Source subreddit :</b> {src}<br>"
            f"<b>Target subreddit :</b> {tgt}<br>"
            f"<b>Upvotes :</b> {int(u)}"
            for src, tgt, u in zip(
                viral["SOURCE_SUBREDDIT"],
                viral["TARGET_SUBREDDIT"],
                viral["ups"]
            )
        ],
        hovertemplate="%{text}<br><extra></extra>"
    ),
        row=i, col=1
    )

fig.update_layout(
    height=300 * len(clusters),
    width=1200,
    title="Moving Average of Ups and Viral Posts per Supercluster",
    xaxis_title="Time",
    yaxis_title="Ups / MA(ups)",
)

    
for i in range(1, len(clusters) + 1):
    fig.update_xaxes(
        title_text="Time",
        tickformat="%Y-%m-%d",
        showticklabels=True,
        tickangle=-45,
        row=i, col=1
    )
    fig.update_yaxes(
        type="log",
        title_text="Ups / MA(ups)",
        row=i, col=1
    )

fig.show()


In [ ]:
import plotly.graph_objects as go
from plotly.subplots import make_subplots

clusters = sorted(dfs_by_supercluster.keys())

fig = make_subplots(
    rows=len(clusters),
    cols=1,
    shared_xaxes=True,
    subplot_titles=[f"Supercluster {c}" for c in clusters]
)

for i, cluster in enumerate(clusters, start=1):
    df_sc = dfs_by_supercluster[cluster]
    df_sc = df_sc.sort_values("TIMESTAMP")
    df_sub = df_sc.iloc[::10]    

    fig.add_trace(
    go.Scatter(
        x=df_sub["TIMESTAMP"],
        y=df_sub["virality_rss_ma"],
        mode="lines",
        name="Moving Average",
        showlegend=(i == 1)
    ),
    row=i, col=1
)
    
    # fig.add_trace(
    #     go.Scatter(
    #         x=df_sc["TIMESTAMP"],
    #         y=df_sc["virality_rss_ma"],
    #         mode="lines",
    #         name="Moving Average",
    #         showlegend=(i == 1)
    #     ),
    #     row=i, col=1
    # )

   
    viral = df_sc[df_sc["is_viral_rss"]]
    fig.add_trace(
        go.Scatter(
        x=viral["TIMESTAMP"],
        y=viral["virality_rss"],
        mode="markers",
        name=f"Viral – cluster {cluster}",
        marker=dict(size=5, symbol="circle-open"),
        showlegend=(i == 1),
        text=[
            f"<b>Source subreddit :</b> {src}<br>"
            f"<b>Target subreddit :</b> {tgt}<br>"
            f"<b>Upvotes :</b> {int(u)}"
            for src, tgt, u in zip(
                viral["SOURCE_SUBREDDIT"],
                viral["TARGET_SUBREDDIT"],
                viral["ups"]
            )
        ],
        hovertemplate="%{text}<br><extra></extra>"
    ),
        row=i, col=1
    )

fig.update_layout(
    height=300 * len(clusters),
    width=1200,
    title="Moving Average of virality rss and Viral Posts per Supercluster",
    xaxis_title="Time",
    yaxis_title="virality_rss / MA",
)

    
for i in range(1, len(clusters) + 1):
    fig.update_xaxes(
        title_text="Time",
        tickformat="%Y-%m-%d",
        showticklabels=True,
        tickangle=-45,
        row=i, col=1
    )
    fig.update_yaxes(
        type="log",
        title_text="virality rss  / MA",
        row=i, col=1
    )

fig.show()


In [ ]:
import os

WINDOW = 50000

output_dir = r"ada-2025-project-standard-deviants-ada\data"
os.makedirs(output_dir, exist_ok=True)


dfs_by_supercluster = {}
viral_by_supercluster = {}
final_by_supercluster = {}

for supercluster, df_sc in df_final.groupby("source_supercluster"):
    df_sc = df_sc.copy()
    df_sc = df_sc.sort_values("TIMESTAMP")

    
    df_sc["ups_ma"] = df_sc["ups"].rolling(WINDOW, min_periods=1000).mean()
    df_sc["ups_std"] = df_sc["ups"].rolling(WINDOW, min_periods=1000).std()

    
    df_sc["is_viral"] = df_sc["ups"] > (df_sc["ups_ma"] + 60 * df_sc["ups_std"])

   
    df_sc["subreddit_occ_index"] = df_sc.groupby("SOURCE_SUBREDDIT").cumcount() + 1

    
    dfs_by_supercluster[supercluster] = df_sc

    
    df_v = df_sc[df_sc["is_viral"]].copy()
    df_v = df_v[["TIMESTAMP", "ups", "SOURCE_SUBREDDIT"]]
    viral_by_supercluster[supercluster] = df_v

    
    df_avg = df_sc[["TIMESTAMP", "ups_ma"]].copy()
    df_avg["SOURCE_SUBREDDIT"] = "Average"
    df_avg = df_avg.rename(columns={"ups_ma": "ups"})

   
    df_final_cluster = pd.concat([df_avg, df_v], ignore_index=True)

    final_by_supercluster[supercluster] = df_final_cluster

for supercluster, df_final_cluster in final_by_supercluster.items():
    filename = f"final_supercluster_{supercluster}.csv"
    df_final_cluster.to_csv(os.path.join(output_dir, filename), index=False)